In [1]:
import warnings
warnings.filterwarnings('ignore')

In [2]:
import numpy as np
import pandas as pd
import matplotlib.pyplot as plt
import lightgbm as lgbm

In [3]:
# 데이터 분할 및 전처리
from sklearn.model_selection import train_test_split
from sklearn.preprocessing import LabelEncoder

# 특성 선택
from sklearn.feature_selection import SequentialFeatureSelector

# 하이퍼파라미터 튜닝
from sklearn.model_selection import RandomizedSearchCV
from sklearn.model_selection import GridSearchCV
from sklearn.metrics import precision_recall_curve
# 모델 평가 지표
from sklearn.metrics import accuracy_score
from sklearn.metrics import precision_score
from sklearn.metrics import recall_score
from sklearn.metrics import f1_score

# 데이터 시각화
import seaborn as sns

### 1. 데이터 로드 및 탐색

#### 1.1 데이터 로드

In [4]:
df_trn = pd.read_csv('train.csv')
df_tst = pd.read_csv('test.csv')

### 2. 데이터 전처리

#### 2.1 범주형 데이터 인코딩

In [5]:
# 범주형 데이터를 라벨 인코딩
cat = ['job','marital','contact','poutcome','education','default','housing','loan','month']
label_encoder = {}
for col in cat:
    le = LabelEncoder()
    df_trn[col] = le.fit_transform(df_trn[col])
    df_tst[col] = le.transform(df_tst[col])
    label_encoder[col] = le

#### 2.2 파생 변수 생성

In [6]:
# 계절을 반환하는 함수 정의
def get_season(month):
    if 3 <= month <= 5:
        return 'spring'
    elif 6 <= month <= 8:
        return 'summer'
    elif 9 <= month <= 11:
        return 'autumn'
    else:
        return 'winter'

In [7]:
# 데이터 전처리 함수 정의
def preprocess_data(df_trn, df_tst):

    le = LabelEncoder()
    
    # pdays 를 갖고 연락여부로 이진분류한 새로운 칼럼 생성
    df_trn['pdays_contacted'] = (df_trn['pdays'] != -1).astype(int)
    df_tst['pdays_contacted'] = (df_tst['pdays'] != -1).astype(int)
    
    # 흠....
    df_trn['duration_per_campaign'] = df_trn['duration'] / (df_trn['campaign'] + 1)
    df_tst['duration_per_campaign'] = df_tst['duration'] / (df_tst['campaign'] + 1)
    
    # day와 month를 통합하여 연속적인 시간 정보를 제공하기 위한 새로운 칼럼 생성
    df_trn['day_of_year'] = df_trn['day'] + (df_trn['month'] - 1) * 30
    df_tst['day_of_year'] = df_tst['day'] + (df_tst['month'] - 1) * 30
    
    # 계별 특성을 학습할 수 있도록 새로운 칼럼 생성
    df_trn['season'] = df_trn['month'].apply(get_season)
    df_tst['season'] = df_tst['month'].apply(get_season)
    # 범주형인 season을 라벨인코딩 수행
    df_trn['season'] = le.fit_transform(df_trn['season'])
    df_tst['season'] = le.transform(df_tst['season'])
    
    return df_trn, df_tst

In [8]:
# 전처리 함수 적용 후 할당
df_trn_preprocessed, df_tst_preprocessed = preprocess_data(df_trn,df_tst)

#### 2.3 Feature와 Target 분리

In [9]:
total_cols = [x for x in df_trn.columns]

id_cols = ['ID']
y_cols = ['label']
x_cols = [x for x in total_cols if x not in id_cols+y_cols]

In [10]:
# feature와 target분리
df_trn_x = df_trn_preprocessed[x_cols]
df_trn_y = df_trn_preprocessed[y_cols].values.ravel()
df_tst_x = df_tst_preprocessed[x_cols]

In [11]:
df_trn_x.info()

<class 'pandas.core.frame.DataFrame'>
RangeIndex: 31647 entries, 0 to 31646
Data columns (total 20 columns):
 #   Column                 Non-Null Count  Dtype  
---  ------                 --------------  -----  
 0   age                    31647 non-null  int64  
 1   job                    31647 non-null  int64  
 2   marital                31647 non-null  int64  
 3   education              31647 non-null  int64  
 4   default                31647 non-null  int64  
 5   balance                31647 non-null  int64  
 6   housing                31647 non-null  int64  
 7   loan                   31647 non-null  int64  
 8   contact                31647 non-null  int64  
 9   day                    31647 non-null  int64  
 10  month                  31647 non-null  int64  
 11  duration               31647 non-null  int64  
 12  campaign               31647 non-null  int64  
 13  pdays                  31647 non-null  int64  
 14  previous               31647 non-null  int64  
 15  po

### 3. 모델 정의 및 학습

#### 3.1 검증 데이터 분리

In [12]:
# 검증 데이터셋 분리
df_retrn_x, df_val_x, df_retrn_y, df_val_y = train_test_split(df_trn_x, df_trn_y, test_size=0.2, random_state=42, stratify=df_trn_y)

#### 3.2 초기 모델 정의 및 학습

In [13]:
# 초기 모델 정의
base_model = lgbm.LGBMClassifier(random_state=42, verbose=-1, class_weight='balanced')
#학습
base_model.fit(df_retrn_x, df_retrn_y)

LGBMClassifier(class_weight='balanced', random_state=42, verbose=-1)

#### 3.3 변수 중요도 분석

In [14]:
# Feature Importance 추출
importances = base_model.feature_importances_
features = df_retrn_x.columns

# 중요도를 데이터프레임으로 저장
importance_df = pd.DataFrame({
    'Feature': features,
    'Importance': importances
}).sort_values(by='Importance', ascending=False)

# 출력
print(importance_df)

                  Feature  Importance
18            day_of_year         588
11               duration         429
5                 balance         275
0                     age         273
17  duration_per_campaign         271
9                     day         214
13                  pdays         184
1                     job         126
8                 contact          93
10                  month          92
12               campaign          74
15               poutcome          71
3               education          67
6                 housing          63
14               previous          54
19                 season          48
2                 marital          41
7                    loan          28
4                 default           9
16        pdays_contacted           0


#### 3.4 변수 선택법

In [15]:
# 변수 선택 모델 정의
sfs = SequentialFeatureSelector(
    base_model,
    n_features_to_select='auto',
    direction='forward',
    scoring='f1',
    cv=5,
    n_jobs=-1
)
# 변수 선택 모델 학습하기
sfs.fit(df_retrn_x, df_retrn_y)

KeyboardInterrupt: 

In [15]:
# 선택된 변수 할당하기
#selected_features = df_retrn_x.columns[sfs.get_support()].tolist()
selected_features = ['age', 'housing', 'contact', 'day', 'duration', 'campaign', 'pdays', 'poutcome', 'duration_per_campaign', 'day_of_year']
print(f"선택된 변수: {selected_features}")

선택된 변수: ['age', 'housing', 'contact', 'day', 'duration', 'campaign', 'pdays', 'poutcome', 'duration_per_campaign', 'day_of_year']


In [16]:
# 선택된 변수로 데이터 재구성
df_retrn_x_selected = df_retrn_x[selected_features]
df_val_x_selected = df_val_x[selected_features]
df_tst_x_selected = df_tst_x[selected_features]

### 4. 모델 최적화

#### 4.1 OPTUNA

In [38]:
X_train, X_val = df_retrn_x_selected, df_val_x_selected
y_train, y_val = df_retrn_y, df_val_y

In [35]:
import optuna
from lightgbm import LGBMClassifier
from sklearn.model_selection import StratifiedKFold, cross_val_score
from sklearn.metrics import f1_score
from lightgbm.callback import early_stopping, log_evaluation

In [46]:
def objective(trial):
#탐색할 하이퍼파라미터 범위 설정(try1과 다른 파라미터 설정) -> try1 바탕으로 하이퍼파라미터 설정해봤으나 overfitting 발생
    param = {
        'class_weight': 'balanced',
        'learning_rate': trial.suggest_loguniform('learning_rate', 1e-3, 1e-1),
        'n_estimators': trial.suggest_int('n_estimators', 800, 2000),
        'max_depth': trial.suggest_int('max_depth', 4, 6),
        'num_leaves': trial.suggest_int('num_leaves', 20, 80),
        'min_child_samples': trial.suggest_int('min_child_samples', 100, 300),
        'subsample': trial.suggest_uniform('subsample', 0.6, 0.8),
        'colsample_bytree': trial.suggest_uniform('colsample_bytree', 0.5, 0.7),
        # 과적합 막기 위해 L1/L2 정규화 과정도 추가
        'reg_alpha': trial.suggest_loguniform('reg_alpha', 1e-1, 10.0),
        'reg_lambda': trial.suggest_loguniform('reg_lambda', 1e-1, 10.0),
        'random_state': 42
    }
    
    model = LGBMClassifier(**param)
    
    # Stratified K-Fold CV
    cv = StratifiedKFold(n_splits=5, shuffle=True, random_state=42)
    scores = cross_val_score(
        model,
        X_train, y_trn,      # 학습 전체 데이터
        cv=cv,
        scoring='f1',
        n_jobs=-1
    )
    return scores.mean()


In [44]:
study = optuna.create_study(direction='maximize')
study.optimize(objective, n_trials=50, timeout=600)  


[I 2025-05-27 03:11:32,603] A new study created in memory with name: no-name-ab5c46f1-65b0-491e-acfc-5a3a50897813


[LightGBM] [Info] Number of positive: 2370, number of negative: 17884
[LightGBM] [Info] Number of positive: 2370, number of negative: 17884
[LightGBM] [Info] Number of positive: 2369, number of negative: 17884
[LightGBM] [Info] Number of positive: 2370, number of negative: 17884
[LightGBM] [Info] Number of positive: 2369, number of negative: 17884
[LightGBM] [Info] Auto-choosing row-wise multi-threading, the overhead of testing was 0.002249 seconds.
You can set `force_row_wise=true` to remove the overhead.
And if memory is not enough, you can set `force_col_wise=true`.
[LightGBM] [Info] Total Bins 1142
[LightGBM] [Info] Auto-choosing row-wise multi-threading, the overhead of testing was 0.002312 seconds.
You can set `force_row_wise=true` to remove the overhead.
And if memory is not enough, you can set `force_col_wise=true`.
[LightGBM] [Info] Total Bins 1141
[LightGBM] [Info] Auto-choosing row-wise multi-threading, the overhead of testing was 0.002038 seconds.
You can set `force_row_wis

[I 2025-05-27 03:11:43,200] Trial 0 finished with value: 0.5013204516980155 and parameters: {'learning_rate': 0.0019814157583448047, 'n_estimators': 1190, 'max_depth': 4, 'num_leaves': 80, 'min_child_samples': 224, 'subsample': 0.6969981117635415, 'colsample_bytree': 0.6751171282384313, 'reg_alpha': 0.259902684696147, 'reg_lambda': 4.377796847848472}. Best is trial 0 with value: 0.5013204516980155.


[LightGBM] [Warning] No further splits with positive gain, best gain: -inf
[LightGBM] [Warning] No further splits with positive gain, best gain: -inf
[LightGBM] [Warning] No further splits with positive gain, best gain: -inf
[LightGBM] [Warning] No further splits with positive gain, best gain: -inf
[LightGBM] [Warning] No further splits with positive gain, best gain: -inf
[LightGBM] [Warning] No further splits with positive gain, best gain: -inf
[LightGBM] [Warning] No further splits with positive gain, best gain: -inf
[LightGBM] [Warning] No further splits with positive gain, best gain: -inf
[LightGBM] [Warning] No further splits with positive gain, best gain: -inf
[LightGBM] [Warning] No further splits with positive gain, best gain: -inf
[LightGBM] [Warning] No further splits with positive gain, best gain: -inf
[LightGBM] [Warning] No further splits with positive gain, best gain: -inf
[LightGBM] [Warning] No further splits with positive gain, best gain: -inf
[LightGBM] [Warning] No f

[I 2025-05-27 03:11:56,318] Trial 1 finished with value: 0.5574877572058077 and parameters: {'learning_rate': 0.004266736442911967, 'n_estimators': 1899, 'max_depth': 4, 'num_leaves': 77, 'min_child_samples': 268, 'subsample': 0.6653406183776683, 'colsample_bytree': 0.6804196733518955, 'reg_alpha': 0.16710616239936285, 'reg_lambda': 6.09892769798153}. Best is trial 1 with value: 0.5574877572058077.


...

[I 2025-05-27 03:21:02,174] Trial 32 finished with value: 0.6100671831021472 and parameters: {'learning_rate': 0.04334737156223725, 'n_estimators': 1746, 'max_depth': 6, 'num_leaves': 27, 'min_child_samples': 124, 'subsample': 0.7267597181484392, 'colsample_bytree': 0.590510552251192, 'reg_alpha': 1.5667378433535784, 'reg_lambda': 1.5667748620403743}. Best is trial 16 with value: 0.6137980918313442.


[LightGBM] [Warning] No further splits with positive gain, best gain: -inf
[LightGBM] [Info] Number of positive: 2369, number of negative: 17884
[LightGBM] [Info] Auto-choosing row-wise multi-threading, the overhead of testing was 0.010637 seconds.
You can set `force_row_wise=true` to remove the overhead.
And if memory is not enough, you can set `force_col_wise=true`.
[LightGBM] [Info] Total Bins 1143
[LightGBM] [Info] Number of data points in the train set: 20253, number of used features: 10
[LightGBM] [Info] [binary:BoostFromScore]: pavg=0.500000 -> initscore=0.000000
[LightGBM] [Info] Start training from score 0.000000
[LightGBM] [Info] Number of positive: 2369, number of negative: 17884
[LightGBM] [Info] Number of positive: 2370, number of negative: 17884
[LightGBM] [Info] Auto-choosing col-wise multi-threading, the overhead of testing was 0.001782 seconds.
You can set `force_col_wise=true` to remove the overhead.
[LightGBM] [Info] Total Bins 1145
[LightGBM] [Info] Number of data p

[I 2025-05-27 03:21:26,206] Trial 33 finished with value: 0.6091284995257091 and parameters: {'learning_rate': 0.050198728346140795, 'n_estimators': 1665, 'max_depth': 6, 'num_leaves': 39, 'min_child_samples': 139, 'subsample': 0.7409486726268757, 'colsample_bytree': 0.5764876019797334, 'reg_alpha': 2.7902663208601988, 'reg_lambda': 1.0948144783585323}. Best is trial 16 with value: 0.6137980918313442.


[LightGBM] [Info] Number of positive: 2369, number of negative: 17884
[LightGBM] [Info] Auto-choosing row-wise multi-threading, the overhead of testing was 0.002450 seconds.
You can set `force_row_wise=true` to remove the overhead.
And if memory is not enough, you can set `force_col_wise=true`.
[LightGBM] [Info] Total Bins 1143
[LightGBM] [Info] Number of data points in the train set: 20253, number of used features: 10
[LightGBM] [Info] [binary:BoostFromScore]: pavg=0.500000 -> initscore=0.000000
[LightGBM] [Info] Start training from score 0.000000
[LightGBM] [Info] Number of positive: 2369, number of negative: 17884
[LightGBM] [Info] Number of positive: 2370, number of negative: 17884
[LightGBM] [Info] Auto-choosing col-wise multi-threading, the overhead of testing was 0.002358 seconds.
You can set `force_col_wise=true` to remove the overhead.
[LightGBM] [Info] Total Bins 1145
[LightGBM] [Info] Auto-choosing row-wise multi-threading, the overhead of testing was 0.001608 seconds.
You c

[I 2025-05-27 03:21:45,196] Trial 34 finished with value: 0.6059321323909229 and parameters: {'learning_rate': 0.021922678948479244, 'n_estimators': 1449, 'max_depth': 6, 'num_leaves': 23, 'min_child_samples': 113, 'subsample': 0.6944676689266751, 'colsample_bytree': 0.6119078845814732, 'reg_alpha': 1.0464826396946019, 'reg_lambda': 4.418692353246105}. Best is trial 16 with value: 0.6137980918313442.


In [24]:
best_params = study.best_trial.params
print("Best params:", best_params)


Best params: {'learning_rate': 0.07511782639347954, 'n_estimators': 873, 'max_depth': 8, 'num_leaves': 111, 'min_child_samples': 61, 'subsample': 0.6395285668950298, 'colsample_bytree': 0.6625031099352803}


In [ ]:
#Best params: {'learning_rate': 0.07511782639347954, 'n_estimators': 873, 'max_depth': 8, 'num_leaves': 111, 'min_child_samples': 61, 'subsample': 0.6395285668950298, 'colsample_bytree': 0.6625031099352803}


##### optuna 시각화

In [25]:
from optuna.visualization import (
    plot_optimization_history,
    plot_param_importances,
    plot_parallel_coordinate,
    plot_slice,
    plot_contour
)

In [26]:
# 1) Trial별 F1-score 추이
fig1 = plot_optimization_history(study)
fig1.show()

# 2) Hyperparameter 중요도 분석
fig2 = plot_param_importances(study)
fig2.show()

# 3) 두 파라미터 조합별 성능 분포 (parallel coordinate)
fig3 = plot_parallel_coordinate(study, params=['learning_rate','n_estimators','max_depth'])
fig3.show()

# 4) 특정 파라미터 주위 성능 (slice plot)
fig4 = plot_slice(study, params=['learning_rate','subsample'])
fig4.show()

# 5) 2차원 성능 등고선 (contour plot)
fig5 = plot_contour(study, params=['learning_rate','num_leaves'])
fig5.show()

##### optuna 그래프 해석

* 파란 점(Objective Value): 각 Trial(실험)마다 얻은 Validation F1-score

* 빨간 선(Best Value): 지금까지 최고 성능이 유지된 값을 이어 그린 것

+ Trial 1→2에서 급격히 성능이 올라간 뒤, 대략 0.60∼0.62 사이에서 **플래토(plateau)** 에 진입

+ 이후 탐색 공간 전반에서 비슷한 성능이 반복 → 지금 범위 내에서는 큰 도약이 어려움을 의미

**learning_rate (≈0.45) 가 가장 큰 영향력을 보임**

* 그다음으로 n_estimators (≈0.19), min_child_samples (≈0.16)

* num_leaves, max_depth 중간,

* subsample, colsample_bytree, reg_alpha, reg_lambda 순으로 중요도 급감

* 색이 진할수록(F1 높을수록), 해당 Trial의 파라미터 값이 어떻게 분포하는지 선으로 이어 줌

* learning_rate ≈ 0.1 ∼ 0.2, max_depth ≈ 5 ∼ 8, n_estimators ≈ 600 ∼ 900 구간에서 짙은 선들이 몰려 있는 모습이 보임



* 왼쪽: learning_rate vs Objective

    * 0.01 미만 구간은 비교적 성능 저조

    * 0.05 ∼ 0.2 구간에서 F1이 전반적으로 높음

* 오른쪽: subsample vs Objective

    * 0.6 ∼ 0.8 사이에서 좋은 Trial이 많고,

    * 0.9 이상에서는 약간 성능이 떨어지는 경향

* learning_rate (x축) 와 num_leaves (y축) 의 조합별 성능 등고선

    * 중간 빛(≈0.60) 영역보다 진한 파란색(≈0.62) 영역이

* learning_rate ≈ 0.1–0.2 × num_leaves ≈ 80–150 구역에 몰려 있음

#### 4.2 최적의 threshold 찾기

In [27]:
#최적의 params 모델에 적용
best_model = LGBMClassifier(**best_params, random_state=42)

#train 데이터 로 학습
best_model.fit(df_retrn_x_selected, df_retrn_y)

# 예측 확률값
y_prob = best_model.predict_proba(df_val_x_selected)[:, 1]  # 양성 클래스 확률

# Precision, Recall, Threshold 계산
precisions, recalls, thresholds = precision_recall_curve(df_val_y, y_prob)

# F1 Score 계산
f1_scores = 2 * (precisions * recalls) / (precisions + recalls + 1e-9)

# 최적 Threshold 선택
best_threshold = thresholds[np.argmax(f1_scores)]
print(f"Best Threshold for F1 Score: {best_threshold}")

# 최적 Threshold 기반 예측
y_pred = (y_prob >= best_threshold).astype(int)

# F1 Score 확인
print(f"Optimized F1 Score: {f1_score(df_val_y, y_pred)}")


Best Threshold for F1 Score: 0.18632668518305587
Optimized F1 Score: 0.615795090715048


In [ ]:
#Best Threshold for F1 Score: 0.18632668518305587
#Optimized F1 Score: 0.615795090715048

### 5. 모델 평가

In [28]:
# threshold 설정
thres=0.1863

In [29]:
# 훈련 데이터에 대한 성능 평가
y_retrn_pred_proba = best_model.predict_proba(df_retrn_x_selected)[:, 1]
y_retrn_pred_label = (y_retrn_pred_proba > thres).astype(int)

print(f"훈련 데이터 Accuracy: {accuracy_score(df_retrn_y, y_retrn_pred_label)}")
print(f"훈련 데이터 Precision: {precision_score(df_retrn_y, y_retrn_pred_label)}")
print(f"훈련 데이터 Recall: {recall_score(df_retrn_y, y_retrn_pred_label)}")
print(f"훈련 데이터 F1 Score: {f1_score(df_retrn_y, y_retrn_pred_label)}")

훈련 데이터 Accuracy: 0.9479796184382036
훈련 데이터 Precision: 0.6962538773562396
훈련 데이터 Recall: 0.9851451721809588
훈련 데이터 F1 Score: 0.8158814483433524


검증 데이터로 성능 평가

In [30]:
# 검증 데이터에 대한 성능 평가
y_val_pred_proba = best_model.predict_proba(df_val_x_selected)[:, 1]
y_val_pred_label = (y_val_pred_proba > thres).astype(int)

print(f"검증 데이터 Accuracy: {accuracy_score(df_val_y, y_val_pred_label)}")
print(f"검증 데이터 Precision: {precision_score(df_val_y, y_val_pred_label)}")
print(f"검증 데이터 Recall: {recall_score(df_val_y, y_val_pred_label)}")
print(f"검증 데이터 F1 Score: {f1_score(df_val_y, y_val_pred_label)}")

검증 데이터 Accuracy: 0.8862559241706162
검증 데이터 Precision: 0.5088183421516755
검증 데이터 Recall: 0.7797297297297298
검증 데이터 F1 Score: 0.615795090715048


> 이전보다 점수가 안나오는 것으로 보아 과적합 (훈련데이터는 점수가 높아졌지만, 검증데이터의 점수는 낮아짐...ㅠ) 



### SHAP

In [45]:
# 1) Train+Validation 합친 전체 데이터로 재학습
X_full = pd.concat([df_retrn_x_selected, df_val_x_selected])
y_full = np.concatenate([df_trn_y, df_val_y])

final_model = LGBMClassifier(**study.best_trial.params, random_state=42)
final_model.fit(X_full, y_full)

[LightGBM] [Fatal] Length of labels differs from the length of #data


LightGBMError: Length of labels differs from the length of #data

### 6. 최종 모델 학습(전체 훈련 데이터)

In [ ]:
df_trn_x_selected = df_trn_x[selected_features]
best_model.fit(df_trn_x_selected, df_trn_y)

LGBMClassifier(class_weight='balanced', colsample_bytree=0.6,
               learning_rate=0.15, max_depth=5, min_child_samples=100,
               n_estimators=400, random_state=42, subsample=0.8, verbose=-1)

### 7. 테스트 데이터에 대한 예측 후 저장하기

#### 7.1 테스트데이터에 대한 예측 수행

In [ ]:
y_tst_pred_proba = best_model.predict_proba(df_tst_x_selected)[:,1]

In [ ]:
y_tst_pred_label = (y_tst_pred_proba > thres).astype(int)

#### 7.2 예측결과 저장하기

In [ ]:
df_submission = pd.read_csv('C:/Users/c0nc2/OneDrive/문서/카카오톡 받은 파일/submission_example.csv')

In [ ]:
df_submission.head()

,ID,label
0,test00001,0
1,test00002,0
2,test00003,0
3,test00004,0
4,test00005,0


In [ ]:
df_submission['label'] = y_tst_pred_label

In [ ]:
df_submission['label'].value_counts()

label
0    11541
1     2023
Name: count, dtype: int64

In [ ]:
# 다하고 눌러라!!!!
filename = 'LightGBM_Ho_final-1.csv'
df_submission.to_csv(filename, index=False)